# Perfilado exploratorio de datos

Este notebook analiza por separado los datasets de los premios GRAMMY y Spotify. Para cada conjunto se genera un informe de calidad y distribucion con **Data Profiling** (ydata-profiling), ademas de un resumen inicial por columna.

## 1. Preparar las dependencias

Desde la carpeta raiz del proyecto, ejecuta `python -m pip install -r requirements.txt` y luego selecciona/reinicia el kernel del notebook. El archivo de dependencias limita NumPy a la version 1.x para evitar incompatibilidades binarias con paquetes ya instalados en el entorno. No es necesario instalar paquetes desde una celda del notebook.

In [9]:
from pathlib import Path

import pandas as pd
from ydata_profiling import ProfileReport


## 2. Encontrar los archivos de entrada

Los dos CSV estan en `data/raw/`. La busqueda recorre la carpeta actual y sus directorios padre, por lo que funciona tanto si Jupyter se inicia desde la raiz del repositorio como desde `gx/notebooks/`. Si no encuentra los datos, la celda falla con una indicacion explicita en vez de continuar con rutas incorrectas.

In [10]:
PROJECT_ROOT = next(
    (
        parent
        for parent in (Path.cwd(), *Path.cwd().parents)
        if (parent / "data" / "raw" / "spotify_dataset.csv").is_file()
        and (parent / "data" / "raw" / "the_grammy_awards.csv").is_file()
    ),
    None,
)

if PROJECT_ROOT is None:
    raise FileNotFoundError(
        "No se encontraron ambos CSV en data/raw. Abre el notebook desde el proyecto."
    )

DATA_DIR = PROJECT_ROOT / "data" / "raw"
SPOTIFY_PATH = DATA_DIR / "spotify_dataset.csv"
GRAMMYS_PATH = DATA_DIR / "the_grammy_awards.csv"

print(f"Raiz del proyecto: {PROJECT_ROOT}")
print(f"Dataset Spotify: {SPOTIFY_PATH}")
print(f"Dataset GRAMMY: {GRAMMYS_PATH}")


Raiz del proyecto: d:\UAO\Quinto Semestre\etl\workshop-2
Dataset Spotify: d:\UAO\Quinto Semestre\etl\workshop-2\data\raw\spotify_dataset.csv
Dataset GRAMMY: d:\UAO\Quinto Semestre\etl\workshop-2\data\raw\the_grammy_awards.csv


## 3. Cargar y comprobar los datasets

Se leen los CSV con su separador predeterminado (coma). El archivo de Spotify contiene una primera columna sin nombre que corresponde al indice exportado; `index_col=0` evita tratar ese indice como una variable del dataset. Se muestran dimensiones y una muestra para confirmar que la lectura fue correcta.

In [11]:
df_spotify = pd.read_csv(SPOTIFY_PATH, index_col=0, low_memory=False)
df_grammys = pd.read_csv(GRAMMYS_PATH, low_memory=False)

datasets = {
    "Spotify": df_spotify,
    "Premios GRAMMY": df_grammys,
}

for name, dataframe in datasets.items():
    if dataframe.empty:
        raise ValueError(f"El dataset {name} no contiene filas.")
    print(f"{name}: {dataframe.shape[0]:,} filas x {dataframe.shape[1]} columnas")

display(df_spotify.head())
display(df_grammys.head())


Spotify: 114,000 filas x 20 columnas
Premios GRAMMY: 4,810 filas x 10 columnas


,track_id,artists,album_name,track_name,popularity,duration_ms,explicit,danceability,energy,key,loudness,mode,speechiness,acousticness,instrumentalness,liveness,valence,tempo,time_signature,track_genre
0,5SuOikwiRyPMVoIQDJUgSV,Gen Hoshino,Comedy,Comedy,73,230666,False,0.676,0.4610,1,-6.746,0,0.1430,0.0322,0.000001,0.3580,0.715,87.917,4,acoustic
1,4qPNDBW1i3p13qLCt0Ki3A,Ben Woodward,Ghost (Acoustic),Ghost - Acoustic,55,149610,False,0.420,0.1660,1,-17.235,1,0.0763,0.9240,0.000006,0.1010,0.267,77.489,4,acoustic
2,1iJBSr7s7jYXzM8EGcbK5b,Ingrid Michaelson;ZAYN,To Begin Again,To Begin Again,57,210826,False,0.438,0.3590,0,-9.734,1,0.0557,0.2100,0.000000,0.1170,0.120,76.332,4,acoustic
3,6lfxq3CG4xtTiEg7opyCyx,Kina Grannis,Crazy Rich Asians (Original Motion Picture Sou...,Can't Help Falling In Love,71,201933,False,0.266,0.0596,0,-18.515,1,0.0363,0.9050,0.000071,0.1320,0.143,181.740,3,acoustic
4,5vjLSffimiIP26QG5WcN2K,Chord Overstreet,Hold On,Hold On,82,198853,False,0.618,0.4430,2,-9.681,1,0.0526,0.4690,0.000000,0.0829,0.167,119.949,4,acoustic


,year,title,published_at,updated_at,category,nominee,artist,workers,img,winner
0,2019,62nd Annual GRAMMY Awards (2019),2020-05-19T05:10:28-07:00,2020-05-19T05:10:28-07:00,Record Of The Year,Bad Guy,Billie Eilish,"Finneas O'Connell, producer; Rob Kinelski & Fi...",https://www.grammy.com/sites/com/files/styles/...,True
1,2019,62nd Annual GRAMMY Awards (2019),2020-05-19T05:10:28-07:00,2020-05-19T05:10:28-07:00,Record Of The Year,"Hey, Ma",Bon Iver,"BJ Burton, Brad Cook, Chris Messina & Justin V...",https://www.grammy.com/sites/com/files/styles/...,True
2,2019,62nd Annual GRAMMY Awards (2019),2020-05-19T05:10:28-07:00,2020-05-19T05:10:28-07:00,Record Of The Year,7 rings,Ariana Grande,"Charles Anderson, Tommy Brown, Michael Foster ...",https://www.grammy.com/sites/com/files/styles/...,True
3,2019,62nd Annual GRAMMY Awards (2019),2020-05-19T05:10:28-07:00,2020-05-19T05:10:28-07:00,Record Of The Year,Hard Place,H.E.R.,"Rodney “Darkchild” Jerkins, producer; Joseph H...",https://www.grammy.com/sites/com/files/styles/...,True
4,2019,62nd Annual GRAMMY Awards (2019),2020-05-19T05:10:28-07:00,2020-05-19T05:10:28-07:00,Record Of The Year,Talk,Khalid,"Disclosure & Denis Kosiak, producers; Ingmar C...",https://www.grammy.com/sites/com/files/styles/...,True


## 4. Resumen inicial de calidad

La tabla compara tipo, valores ausentes y cardinalidad por columna. Luego se ejecuta un catalogo de reglas orientado a los analisis objetivo. **CRITICA** bloquea una conclusion; **ALTA** puede sesgar conteos o comparaciones; **MEDIA** requiere filtrar o revisar valores; **BAJA** es informativa. Los umbrales son criterios iniciales explicitos para este proyecto, no estandares universales.


In [12]:
column_summaries = []
for dataset_name, dataframe in datasets.items():
    column_summary = pd.DataFrame(
        {
            "dataset": dataset_name,
            "dtype": dataframe.dtypes.astype(str),
            "missing_values": dataframe.isna().sum(),
            "missing_percent": (dataframe.isna().mean() * 100).round(2),
            "distinct_values": dataframe.nunique(dropna=True),
        }
    )
    column_summaries.append(column_summary)

display(pd.concat(column_summaries).rename_axis("column").reset_index())


,column,dataset,dtype,missing_values,missing_percent,distinct_values
0,track_id,Spotify,object,0,0.00,89741
1,artists,Spotify,object,1,0.00,31437
2,album_name,Spotify,object,1,0.00,46589
3,track_name,Spotify,object,1,0.00,73608
4,popularity,Spotify,int64,0,0.00,101
5,duration_ms,Spotify,int64,0,0.00,50697
6,explicit,Spotify,bool,0,0.00,2
7,danceability,Spotify,float64,0,0.00,1174
8,energy,Spotify,float64,0,0.00,2083
9,key,Spotify,int64,0,0.00,12


In [13]:
quality_rules = []


def add_quality_rule(source, rule, metric, threshold, severity, observed, passed, impact):
    quality_rules.append(
        {
            "source": source,
            "rule": rule,
            "metric": metric,
            "threshold": threshold,
            "severity_if_failed": severity,
            "observed": observed,
            "result": "CUMPLE" if passed else "NO CUMPLE",
            "analysis_impact": impact,
        }
    )


grammy_years = pd.to_numeric(df_grammys["year"], errors="coerce")
unique_years = sorted(grammy_years.dropna().astype(int).unique())
year_span = list(range(unique_years[0], unique_years[-1] + 1)) if unique_years else []
artist_coverage = df_grammys["artist"].notna().mean()
multi_credit_artists = df_grammys["artist"].fillna("").str.contains(r"[,;&]", regex=True).sum()
winner_values = set(df_grammys["winner"].dropna().unique())

add_quality_rule(
    "GRAMMY", "Cobertura de artist para ranking", "Filas con artist informado",
    ">= 95%", "ALTA", f"{artist_coverage:.2%}", artist_coverage >= 0.95,
    "Los nulos omiten nominaciones del ranking de artistas.",
)
add_quality_rule(
    "GRAMMY", "Creditos multiples normalizados", "Filas con varios creditos aparentes en artist",
    "0 filas sin separar/explotar creditos", "ALTA", f"{multi_credit_artists:,} filas",
    multi_credit_artists == 0,
    "Contar la cadena completa como un artista distorsiona el ranking de colaboradores.",
)
add_quality_rule(
    "GRAMMY", "Ambos estados de ganador disponibles", "Valores distintos no nulos de winner",
    "Deben existir True y False, sin nulos", "CRITICA", str(sorted(winner_values, key=str)),
    winner_values == {True, False} and df_grammys["winner"].notna().all(),
    "No se puede comparar ganadores con el total de nominados ni calcular perdedores.",
)
grammy_key_duplicates = df_grammys.duplicated(["year", "category", "nominee"], keep=False).sum()
add_quality_rule(
    "GRAMMY", "Unicidad anio-categoria-nominado", "Filas involucradas en claves repetidas",
    "0", "ALTA", f"{grammy_key_duplicates:,} filas", grammy_key_duplicates == 0,
    "Las repeticiones inflarian conteos anuales y por categoria.",
)
years_are_valid = (
    grammy_years.notna().all()
    and grammy_years.eq(grammy_years.round()).all()
    and unique_years == year_span
    and bool(unique_years)
)
add_quality_rule(
    "GRAMMY", "Anio valido y serie anual continua", "Rango y huecos entre anios observados",
    "Anios enteros; sin huecos", "ALTA",
    f"{unique_years[0]}-{unique_years[-1]}; {len(year_span) - len(unique_years)} huecos" if unique_years else "Sin anios validos",
    years_are_valid, "Huecos o anios invalidos distorsionan la evolucion anual.",
)
nominee_coverage = df_grammys["nominee"].notna().mean()
add_quality_rule(
    "GRAMMY", "Cobertura de nominee", "Filas con nominee informado", ">= 99.5%",
    "MEDIA", f"{nominee_coverage:.2%}", nominee_coverage >= 0.995,
    "Los nulos impiden asignar registros a categorias y conteos de nominaciones.",
)

spotify_genre_counts = df_spotify.groupby("track_genre").size()
min_genre_rows = int(spotify_genre_counts.min()) if not spotify_genre_counts.empty else 0
duplicate_rows = int(df_spotify.duplicated().sum())
duplicate_rate = df_spotify.duplicated().mean()
audio_ratio_columns = [
    "danceability", "energy", "speechiness", "acousticness",
    "instrumentalness", "liveness", "valence",
]
audio_ratios_valid = all(df_spotify[column].between(0, 1).all() for column in audio_ratio_columns)
add_quality_rule(
    "Spotify", "Soporte minimo por genero", "Minimo de filas en un genero",
    ">= 100 filas por genero", "ALTA", f"{min_genre_rows:,} filas; {len(spotify_genre_counts)} generos",
    min_genre_rows >= 100, "Con poco soporte, el top 10 por popularidad promedio seria inestable.",
)
invalid_popularity = int((~df_spotify["popularity"].between(0, 100)).sum())
add_quality_rule(
    "Spotify", "Popularidad dentro de escala", "Valores fuera de [0, 100]", "0",
    "ALTA", f"{invalid_popularity:,} filas", invalid_popularity == 0,
    "Valores fuera de escala alteran promedios y ordenamientos por genero.",
)
invalid_audio = sum(int((~df_spotify[column].between(0, 1)).sum()) for column in audio_ratio_columns)
add_quality_rule(
    "Spotify", "Caracteristicas proporcionales de audio validas", "Valores fuera de [0, 1]",
    "0", "ALTA", f"{invalid_audio:,} valores", audio_ratios_valid,
    "Valores invalidos contaminan los promedios de caracteristicas por genero.",
)
invalid_duration = int((df_spotify["duration_ms"] <= 0).sum())
add_quality_rule(
    "Spotify", "Duracion positiva", "Filas con duration_ms <= 0", "0", "MEDIA",
    f"{invalid_duration:,} filas", invalid_duration == 0,
    "Duraciones no positivas se deben excluir o corregir antes de promediar.",
)
invalid_tempo = int((df_spotify["tempo"] <= 0).sum())
add_quality_rule(
    "Spotify", "Tempo positivo", "Filas con tempo <= 0", "0", "MEDIA",
    f"{invalid_tempo:,} filas", invalid_tempo == 0,
    "Tempo cero no representa un valor musical valido y sesga el promedio por genero.",
)
add_quality_rule(
    "Spotify", "Sin filas duplicadas exactas", "Duplicados exactos y porcentaje", "0 filas",
    "ALTA", f"{duplicate_rows:,} ({duplicate_rate:.2%})", duplicate_rows == 0,
    "Duplicados exactos sobreponderan canciones en promedios de popularidad y audio.",
)
invalid_key = int((~df_spotify["key"].between(-1, 11)).sum())
add_quality_rule(
    "Spotify", "Dominio valido de key", "Valores fuera de [-1, 11]", "0",
    "ALTA", f"{invalid_key:,} filas", invalid_key == 0,
    "Claves musicales fuera del codigo permitido invalidan comparaciones por genero.",
)
invalid_mode = int((~df_spotify["mode"].isin([0, 1])).sum())
add_quality_rule(
    "Spotify", "Dominio valido de mode", "Valores fuera de {0, 1}", "0",
    "ALTA", f"{invalid_mode:,} filas", invalid_mode == 0,
    "Modos fuera del dominio esperado no son comparables entre generos.",
)
invalid_time_signature = int((~df_spotify["time_signature"].between(0, 7)).sum())
add_quality_rule(
    "Spotify", "Dominio valido de time_signature", "Valores fuera de [0, 7]", "0",
    "ALTA", f"{invalid_time_signature:,} filas", invalid_time_signature == 0,
    "Firmas de tiempo fuera del dominio codificado invalidan la comparacion por genero.",
)
spotify_targets = ["track_genre", "popularity", *audio_ratio_columns, "duration_ms", "tempo", "loudness", "key", "mode", "time_signature"]
min_target_coverage = df_spotify[spotify_targets].notna().mean().min()
add_quality_rule(
    "Spotify", "Completitud de variables objetivo", "Menor porcentaje no nulo por columna",
    ">= 99.5%", "ALTA", f"{min_target_coverage:.2%}", min_target_coverage >= 0.995,
    "Nulos cambian el tamano efectivo de muestra de los promedios por genero.",
)

quality_report = pd.DataFrame(quality_rules)
display(quality_report)

,source,rule,metric,threshold,severity_if_failed,observed,result,analysis_impact
0,GRAMMY,Cobertura de artist para ranking,Filas con artist informado,>= 95%,ALTA,61.75%,NO CUMPLE,Los nulos omiten nominaciones del ranking de a...
1,GRAMMY,Creditos multiples normalizados,Filas con varios creditos aparentes en artist,0 filas sin separar/explotar creditos,ALTA,448 filas,NO CUMPLE,Contar la cadena completa como un artista dist...
2,GRAMMY,Ambos estados de ganador disponibles,Valores distintos no nulos de winner,"Deben existir True y False, sin nulos",CRITICA,[np.True_],NO CUMPLE,No se puede comparar ganadores con el total de...
3,GRAMMY,Unicidad a?o-categor?a-nominado,Filas involucradas en claves repetidas,0,ALTA,0 filas,CUMPLE,Las repeticiones inflarian conteos anuales y p...
4,GRAMMY,A?o valido y serie anual continua,Rango y huecos entre a?os observados,A?os enteros; sin huecos,ALTA,1958-2019; 0 huecos,CUMPLE,Huecos o a?os invalidos distorsionan la evoluc...
5,GRAMMY,Cobertura de nominee,Filas con nominee informado,>= 99.5%,MEDIA,99.88%,CUMPLE,Los nulos impiden asignar registros a categori...
6,Spotify,Soporte minimo por genero,Minimo de filas en un genero,>= 100 filas por genero,ALTA,"1,000 filas; 114 generos",CUMPLE,"Con poco soporte, el top 10 por popularidad pr..."
7,Spotify,Popularidad dentro de escala,"Valores fuera de [0, 100]",0,ALTA,0 filas,CUMPLE,Valores fuera de escala alteran promedios y or...
8,Spotify,Caracteristicas proporcionales de audio validas,"Valores fuera de [0, 1]",0,ALTA,0 valores,CUMPLE,Valores invalidos contaminan los promedios de ...
9,Spotify,Duracion positiva,Filas con duration_ms <= 0,0,MEDIA,1 filas,NO CUMPLE,Duraciones no positivas se deben excluir o cor...


## 5. Data profiling: Premios GRAMMY

Este informe se calcula exclusivamente sobre `df_grammys`. Explora estructura, tipos, distribuciones, valores ausentes, duplicados, alertas y relaciones entre variables. Revisa especialmente los campos temporales, categoria, nominado, artista y ganador.

In [14]:
profile_grammys = ProfileReport(
    df_grammys,
    title="Perfil de datos - Premios GRAMMY",
    explorative=True,
)
profile_grammys.to_notebook_iframe()


Summarize dataset:   0%|          | 0/5 [00:00<?, ?it/s]

100%|██████████| 10/10 [00:00<00:00, 33.92it/s]


Generate report structure:   0%|          | 0/1 [00:00<?, ?it/s]

Render HTML:   0%|          | 0/1 [00:00<?, ?it/s]

### Hallazgos que afectan los analisis GRAMMY

El perfil y las reglas muestran limites directos para los analisis: `artist` no esta informado en una parte considerable de las filas y algunos valores contienen creditos de varias personas. Un conteo directo puede omitir artistas o tratar una colaboracion como una sola entidad. Ademas, `winner` solo contiene `True`: los registros representan ganadores o el campo fue construido asi, pero esta fuente no permite distinguir nominados no ganadores. El analisis de categorias puede contar registros/ganadores observados, no comparar ganadores frente al total de nominaciones. Confirma la semantica con la fuente original antes de llamar a esa metrica "nominaciones".

Como controles favorables, el periodo observado abarca 1958-2019 sin anios faltantes y no hay duplicados en la clave candidata `year-category-nominee`. Los resultados exactos y umbrales se recalculan en el catalogo de reglas.


## 6. Data profiling: Spotify

Se genera un segundo informe independiente, esta vez solo sobre `df_spotify`. Examina las variables musicales y de popularidad, como duracion, explicitud, bailabilidad, energia, tonalidad, acustica, tempo y genero. Compara las alertas de este informe con el resumen inicial, prestando atencion a valores extremos, columnas constantes y registros repetidos.

In [15]:
profile_spotify = ProfileReport(
    df_spotify,
    title="Perfil de datos - Spotify",
    explorative=True,
)
profile_spotify.to_notebook_iframe()


Summarize dataset:   0%|          | 0/5 [00:00<?, ?it/s]

100%|██████████| 20/20 [00:04<00:00,  4.68it/s]


Generate report structure:   0%|          | 0/1 [00:00<?, ?it/s]

Render HTML:   0%|          | 0/1 [00:00<?, ?it/s]

### Hallazgos que afectan los analisis Spotify

No hay valores ausentes en las columnas analiticas y los 114 generos tienen 1.000 filas cada uno, con igual soporte bruto para comparar promedios; esto no garantiza que la muestra sea representativa. Hay 450 filas duplicadas exactamente, capaces de sobreponderar canciones, y aparecen valores no validos para promedios de tempo (157 ceros) y duracion (una fila con cero). Las reglas identifican estos casos para excluirlos o resolverlos antes de publicar resultados.

`track_id` aparece en mas de un genero; no debe usarse como llave unica global ni eliminarse sin considerar `track_genre`, porque una cancion puede estar asignada a varias etiquetas. Conserva el genero como dimension, elimina duplicados exactos y valida que representa cada repeticion antes de deduplicar por cancion. Las siete variables proporcionales de audio deben permanecer en [0, 1]; popularidad debe permanecer en [0, 100].

`key`, `mode` y `time_signature` son codigos categoricos; compara sus frecuencias o distribuciones, no sus medias aritmeticas. `loudness`, `tempo` y `duration_ms` son continuas pero usan escalas distintas, asi que no interpretes sus magnitudes como directamente equivalentes.